## Visualize ensemble reconstruction results

In [17]:
import jax
jax.config.update('jax_platform_name', 'cpu')
import os 
os.environ['CUDA_VISIBLE_DEVICES'] = ''

import sys 
sys.path.insert(1, '../')

import plotly.graph_objs as go
from plotly.offline import iplot
import plotly.io as pio

from jax import numpy as jnp
import numpy as np

from scipy.ndimage import gaussian_filter

import matplotlib.pyplot as plt
import matplotlib as mpl

from tqdm.auto import tqdm, trange

import plotly.graph_objects as go
from plotly.subplots import make_subplots
from plotly.offline import init_notebook_mode

init_notebook_mode(connected=True) 

In [3]:
pm_seed = 4
num_its = 1

# i_list = range(64)
i_list = range(128)
# i_list = range(1)
# i_list = list(range(0, 0+num_its)) + list(range(25, 25+num_its)) + list(range(50, 50+num_its)) + list(range(75, 75+num_its))
save_dirs = ['../../exp/vol_jwst%d_L_2_Lz_5_proj_gg_shape_sigma_0.25_lam_0.001/%d'%(pm_seed, i) for i in i_list]

# wiener_recon = jnp.load('../../wiener_recon/pm%d_wiener.npy'%pm_seed).transpose((1,2,0))
wiener_recon = jnp.load('/srv/tmp/brandon/abacus/wiener_recon/wiener_jwst_4.npy').transpose(1, 2, 0)
print(wiener_recon.shape)
ddpm_recon = jnp.load('/srv/tmp/brandon/abacus/wiener_recon/ddpm_jwst_4.npy')[:, 20:89, -69:] .transpose(1, 2, 0)
ddpm_samples = jnp.load('/srv/tmp/brandon/abacus/wiener_recon/ddpm_jwst_4_samples.npy')[:, :, 20:89, -69:].transpose(0, 2, 3, 1)
density_paths = [save_dir + '/density/density_500.p' for save_dir in save_dirs]
# density_paths_2 = [save_dir + '/density/density_500.p' for save_dir in save_dirs_2]

res = 69

CUDA backend failed to initialize: jaxlib/cuda/versions_helpers.cc:98: operation cuInit(0) failed: CUDA_ERROR_NO_DEVICE (Set TF_CPP_MIN_LOG_LEVEL=0 and rerun for more info.)


(69, 69, 20)


In [4]:
def mean_subtract(vol, axis=(0,1)): 
    return vol - jnp.mean(vol, axis=axis, keepdims=True)

densities = [mean_subtract(jnp.load(density_path).reshape(res, res, 20)) for density_path in density_paths]
densities_arr = jnp.array(densities)
densities_mean = jnp.mean(densities_arr, axis=0)

density_gt = jnp.load(save_dirs[-1] + '/../density_gt.p').reshape(res, res, 20)

pws = jnp.load(save_dirs[0] + '/../pws.npy')
pws_ein = pws.reshape(-1, res, res, 20)

density_gt = mean_subtract(density_gt)
ddpm_recon = mean_subtract(ddpm_recon)
wiener_recon = mean_subtract(wiener_recon)

print(densities_mean.shape)
print(ddpm_recon.shape)
print(wiener_recon.shape)

(69, 69, 20)
(69, 69, 20)
(69, 69, 20)


In [5]:
from functools import partial
def get_pcc(gt, recon):
    gt = mean_subtract(gt).flatten()
    recon = mean_subtract(recon).flatten()
    return np.corrcoef(gt, recon)[0, 1]

def lightcone_avg(metric, gt, recon, return_metrics=False):
    metrics = np.array([metric(gt[..., i], recon[..., i]) for i in range(gt.shape[-1])])
    if return_metrics: 
        return np.mean(metrics, axis=0), metrics
    else: 
        return np.mean(metrics, axis=0)

get_pcc_avg = partial(lightcone_avg, get_pcc)

pccs_nn = jnp.array([get_pcc_avg(density_gt[..., :12], densities_arr[i, ..., :12]) for i in range(128)])
pccs_dm = jnp.array([get_pcc_avg(density_gt[..., :12], ddpm_samples[i, ..., :12]) for i in range(128)])

nn_inds_sort = jnp.argsort(pccs_nn)

best_nn = densities_arr[jnp.argmax(pccs_nn)]
print(jnp.max(pccs_nn))

best_dm = ddpm_samples[jnp.argmax(pccs_dm)]
print(jnp.max(pccs_dm))


0.19783038
0.14870761


In [6]:
X, Y, Z = np.mgrid[:69, :69, :12]
X = 69 - X
Z = 12 - Z

def zoom_out_same_pov(fig, scale=1.3):
    cam_json = (fig.layout.scene.camera.to_plotly_json()
                if fig.layout.scene.camera is not None else {})
    eye = cam_json.get("eye", {"x": 1.25, "y": 1.25, "z": 1.25})
    new_eye = {k: float(eye.get(k, 1.25)) * scale for k in ("x","y","z")}
    fig.update_layout(scene_camera=dict(eye=new_eye))

In [7]:
density_gt_nofilter = gaussian_filter(density_gt, (2, 2, 0.), mode='constant')[..., :12]
density_gt_filter = gaussian_filter(density_gt, (2, 2, 4.), mode='constant')[..., :12]
wiener_recon_filter = gaussian_filter(wiener_recon, (2, 2, 0))[..., :12]
ddpm_recon_filter = gaussian_filter(ddpm_recon, (2, 2, 0))[..., :12]
neur_recon_filter = gaussian_filter(densities_mean, (2, 2, 0))[..., :12]

ddpm_sample_filter = gaussian_filter(ddpm_samples[jnp.argmax(pccs_dm)], (2, 2, 0))[..., :12]
neur_sample_filter = gaussian_filter(densities_arr[nn_inds_sort[-3]], (2, 2, 0))[..., :12]

In [ ]:
for i in trange(12):
    ddpm_sample_filter = gaussian_filter(ddpm_samples[i], (2, 2, 0))[..., :12]
    fig = go.Figure(data=go.Volume(
        x=Z.flatten(),y=Y.flatten(), z=X.flatten(),
        value=ddpm_sample_filter.flatten(),
        isomin=0.4,
        opacity=0.15,
        surface_count=12,
        showscale=False
        ))

    fig.update_layout(scene_aspectmode='manual', 
                    scene_aspectratio=dict(x=1, y=1, z=1))

    fig.update_scenes(
        xaxis_showticklabels=False, yaxis_showticklabels=False, zaxis_showticklabels=False,
        xaxis_title_text='', yaxis_title_text='', zaxis_title_text=''
    )

    fig.update_layout(
        margin=dict(l=0, r=0, t=0, b=0),   # kill outer margins
        # paper_bgcolor='rgba(0,0,0,0)'      # transparent background (helps if you post-trim)
    )


    # Example: 30% wider framing
    zoom_out_same_pov(fig, scale=1.3)

    fig.update_traces(colorscale='Inferno') 

    fig.update_layout(
        title=dict(
            text="",
            x=0.5,                 # center
            xanchor="center",
            y=0.95,                # a bit lower than the very top (optional)
            yanchor="top",
            font=dict(size=22),
            pad=dict(t=10, b=10)
        )
    )
    pio.write_image(fig, f"./dm_sample_gif/sample_{i:03d}.png")

In [18]:
for i in trange(12):
    neur_sample_filter = gaussian_filter(densities_arr[i], (2, 2, 0))[..., :12]
    fig = go.Figure(data=go.Volume(
        x=Z.flatten(),y=Y.flatten(), z=X.flatten(),
        value=neur_sample_filter.flatten(),
        isomin=0.4,
        opacity=0.15,
        surface_count=12,
        showscale=False
        ))

    fig.update_layout(scene_aspectmode='manual', 
                    scene_aspectratio=dict(x=1, y=1, z=1))

    fig.update_scenes(
        xaxis_showticklabels=False, yaxis_showticklabels=False, zaxis_showticklabels=False,
        xaxis_title_text='', yaxis_title_text='', zaxis_title_text=''
    )

    fig.update_layout(
        margin=dict(l=0, r=0, t=0, b=0),   # kill outer margins
        # paper_bgcolor='rgba(0,0,0,0)'      # transparent background (helps if you post-trim)
    )


    # Example: 30% wider framing
    zoom_out_same_pov(fig, scale=1.3)

    fig.update_traces(colorscale='Inferno') 

    fig.update_layout(
        title=dict(
            text="",
            x=0.5,                 # center
            xanchor="center",
            y=0.95,                # a bit lower than the very top (optional)
            yanchor="top",
            font=dict(size=22),
            pad=dict(t=10, b=10)
        )
    )
    pio.write_image(fig, f"./nn_sample_gif/sample_{i:03d}.png")

  0%|          | 0/12 [00:00<?, ?it/s]

In [20]:
fig = go.Figure(data=go.Volume(
    x=Z.flatten(),y=Y.flatten(), z=X.flatten(),
    value=ddpm_recon_filter.flatten(),
    isomin=0.4,
    opacity=0.15,
    surface_count=12,
    showscale=False
    ))

fig.update_layout(scene_aspectmode='manual', 
                  scene_aspectratio=dict(x=1, y=1, z=1))

fig.update_scenes(
    xaxis_showticklabels=False, yaxis_showticklabels=False, zaxis_showticklabels=False,
    xaxis_title_text='', yaxis_title_text='', zaxis_title_text=''
)

fig.update_layout(
    margin=dict(l=0, r=0, t=0, b=0),   # kill outer margins
    # paper_bgcolor='rgba(0,0,0,0)'      # transparent background (helps if you post-trim)
)


# Example: 30% wider framing
zoom_out_same_pov(fig, scale=1.3)

fig.update_traces(colorscale='Inferno') 

fig.update_layout(
    title=dict(
        text="",
        x=0.5,                 # center
        xanchor="center",
        y=0.95,                # a bit lower than the very top (optional)
        yanchor="top",
        font=dict(size=22),
        pad=dict(t=10, b=10)
    )
)
pio.write_image(fig, "dm.png")

fig.show()

In [19]:
fig = go.Figure(data=go.Volume(
    x=Z.flatten(),y=Y.flatten(), z=X.flatten(),
    value=neur_recon_filter.flatten(),
    isomin=0.4,
    opacity=0.15,
    surface_count=12,
    showscale=False
    ))

fig.update_layout(scene_aspectmode='manual', 
                  scene_aspectratio=dict(x=1, y=1, z=1))

fig.update_scenes(
    xaxis_showticklabels=False, yaxis_showticklabels=False, zaxis_showticklabels=False,
    xaxis_title_text='', yaxis_title_text='', zaxis_title_text=''
)

fig.update_layout(
    margin=dict(l=0, r=0, t=0, b=0),   # kill outer margins
    # paper_bgcolor='rgba(0,0,0,0)'      # transparent background (helps if you post-trim)
)


# Example: 30% wider framing
zoom_out_same_pov(fig, scale=1.3)

fig.update_traces(colorscale='Inferno') 

fig.update_layout(
    title=dict(
        text="",
        x=0.5,                 # center
        xanchor="center",
        y=0.95,                # a bit lower than the very top (optional)
        yanchor="top",
        font=dict(size=22),
        pad=dict(t=10, b=10)
    )
)
pio.write_image(fig, "nn.png")

fig.show()

In [21]:
fig = go.Figure(data=go.Volume(
    x=Z.flatten(),y=Y.flatten(), z=X.flatten(),
    value=density_gt_nofilter.flatten(),
    isomin=0.4,
    opacity=0.15,
    surface_count=12,
    showscale=False
    ))

fig.update_layout(scene_aspectmode='manual', 
                  scene_aspectratio=dict(x=1, y=1, z=1))

fig.update_scenes(
    xaxis_showticklabels=False, yaxis_showticklabels=False, zaxis_showticklabels=False,
    xaxis_title_text='', yaxis_title_text='', zaxis_title_text=''
)

fig.update_layout(
    margin=dict(l=0, r=0, t=0, b=0),   # kill outer margins
    # paper_bgcolor='rgba(0,0,0,0)'      # transparent background (helps if you post-trim)
)


# Example: 30% wider framing
zoom_out_same_pov(fig, scale=1.3)

fig.update_traces(colorscale='Inferno') 

fig.update_layout(
    title=dict(
        text="",
        x=0.5,                 # center
        xanchor="center",
        y=0.95,                # a bit lower than the very top (optional)
        yanchor="top",
        font=dict(size=22),
        pad=dict(t=10, b=10)
    )
)
pio.write_image(fig, "gt.png")

fig.show()